In [1]:
!pip install -q -U \
    "transformers>=5.0.0" \
    accelerate \
    safetensors \
    sentencepiece \
    soundfile \
    librosa \
    snac \
    vocos \
    huggingface-hub

     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 3.7/3.7 MB 54.3 MB/s eta 0:00:00
  Preparing metadata (setup.py) ... done
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 12.8/12.8 MB 118.0 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 294.6/294.6 kB 15.9 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 839.9/839.9 kB 69.1 MB/s eta 0:00:00
ERROR: pip's dependency resolver does not currently take into account all the packages that are installed. This behaviour is the source of the following dependency conflicts.
ipython 7.34.0 requires jedi>=0.16, which is not installed.
datasets 4.8.5 requires huggingface-hub<2.0,>=0.25.0, but you have huggingface-hub 2.2.0 which is incompatible.
diffusers 0.41.0 requires huggingface-hub<2.0,>=1.32.0, but you have huggingface-hub 2.2.0 which is incompatible.
moviepy 1.0.3 requires decorator<5.0,>=4.0.2, but you have decorator 5.3.1 which is incompatible.


In [2]:
!pip install -q \
    "git+https://github.com/Bodhan-AI/bodhan_genai.git"

  Installing build dependencies ... done
  Getting requirements to build wheel ... done
  Preparing metadata (pyproject.toml) ... done
ERROR: Package 'bodhan-genai' requires a different Python: 3.13.15 not in '<3.13,>=3.12'


In [3]:
import transformers
import torch

print("Transformers:", transformers.__version__)
print("PyTorch:", torch.__version__)
print("CUDA:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))

Transformers: 5.20.2
PyTorch: 2.11.0+cu130
CUDA: True
GPU: NVIDIA A100-SXM4-40GB


In [5]:
!pip uninstall -y bodhan-genai

In [6]:
!pip install -q -U \
    "transformers>=5.0.0" \
    accelerate \
    snac \
    soundfile

In [8]:
!pip install -q -U huggingface_hub

In [9]:
from huggingface_hub import login

login()

In [10]:
from huggingface_hub import snapshot_download

MODEL_ID = "bodhan-ai/indic-speak"

model_path = snapshot_download(
    repo_id=MODEL_ID
)

print(model_path)

Reconstructing (incomplete total...): |          |  0.00B /  0.00B            

Fetching 21 files:   0%|          | 0/21 [00:00<?, ?it/s]

/root/.cache/huggingface/hub/models--bodhan-ai--indic-speak/snapshots/76e0814f189321efe550011850cd288dae366aad


In [11]:
import os

for root, dirs, files in os.walk(model_path):
    level = root.replace(model_path, "").count(os.sep)
    indent = "  " * level

    print(f"{indent}{os.path.basename(root)}/")

    for file in files[:10]:
        print(f"{indent}  {file}")

76e0814f189321efe550011850cd288dae366aad/
  README.md
  config.json
  voices.md
  inference.py
  .gitattributes
  generation_config.json
  indic-open-license.md
  Bodhan_AI_Open_Model_License.md
  token_contract.md
  tokenizer.json
  vocos/
    load.py
    __init__.py
    config.yaml
    best.pt
    model.py
    __pycache__/
      __init__.cpython-312.pyc
      model.cpython-312.pyc
      load.cpython-312.pyc


In [12]:
import sys

sys.path.insert(0, model_path)

from inference import TTS

print("✅ Indic-Speak TTS imported")

✅ Indic-Speak TTS imported


In [13]:
tts = TTS(model_path)

print("✅ Indic-Speak loaded successfully")

Loading weights:   0%|          | 0/254 [00:00<?, ?it/s]

config.json:   0%|          | 0.00/300 [00:00<?, ?B/s]

pytorch_model.bin: reconstructing file:   0%|          |  0.00B / 79.5MB            

pytorch_model.bin: downloading bytes:           |  0.00B            

✅ Indic-Speak loaded successfully


In [14]:
text = "നമസ്കാരം, സുഖമാണോ? ഇന്ന് എങ്ങനെയുണ്ട്?"

In [15]:
print(tts)

In [16]:
text = "നമസ്കാരം, സുഖമാണോ? ഇന്ന് എങ്ങനെയുണ്ട്?"

wav = tts(
    text,
    speaker="S1"
)

print(type(wav))

<class 'numpy.ndarray'>


In [17]:
tts.save(
    "/content/malayalam_test.wav",
    wav
)

print("✅ Saved: /content/malayalam_test.wav")

✅ Saved: /content/malayalam_test.wav


In [18]:
from IPython.display import Audio, display

display(
    Audio(
        "/content/malayalam_test.wav",
        autoplay=True
    )
)

In [19]:
# Inspect the TTS object
print(tts)

# Inspect useful attributes
print("\nAttributes:")
print([x for x in dir(tts) if not x.startswith("_")])


Attributes:
['device', 'lm', 'sample_rate', 'save', 'snac', 'tok', 'vocos']


In [20]:
for attr in ["speakers", "speaker", "speaker_names", "voices"]:
    if hasattr(tts, attr):
        print(f"\n{attr}:")
        print(getattr(tts, attr))

In [29]:
wav = tts(
    "എനിക്ക് ഇന്ന് വളരെ സന്തോഷമാണ്.",
    speaker="S3",
    style="SAD",
    temperature=0.6,
    top_p=0.9,
    top_k=50
)

tts.save(
    "/content/malayalam_sad.wav",
    wav
)

'/content/malayalam_sad.wav'

In [31]:
from IPython.display import Audio, display

display(
    Audio(
        "/content/malayalam_sad.wav",
        autoplay=True
    )
)

In [38]:
import torch
from transformers import AutoTokenizer, AutoModelForCausalLM

QWEN_ID = "Qwen/Qwen3-8B"

print("Loading tokenizer...")

qwen_tokenizer = AutoTokenizer.from_pretrained(
    QWEN_ID
)

print("Loading Qwen3-8B...")

qwen_model = AutoModelForCausalLM.from_pretrained(
    QWEN_ID,
    torch_dtype=torch.bfloat16,
    device_map="auto"
)

qwen_model.eval()

print("✅ Qwen3-8B loaded")
print("Device:", qwen_model.device)

Loading tokenizer...


config.json:   0%|          | 0.00/728 [00:00<?, ?B/s]

tokenizer_config.json:   0%|          | 0.00/9.73k [00:00<?, ?B/s]

vocab.json:   0%|          | 0.00/2.78M [00:00<?, ?B/s]

merges.txt:   0%|          | 0.00/1.67M [00:00<?, ?B/s]

...

Reconstructing (incomplete total...): |          |  0.00B /  0.00B            

Fetching 5 files:   0%|          | 0/5 [00:00<?, ?it/s]

Loading weights:   0%|          | 0/399 [00:00<?, ?it/s]

generation_config.json:   0%|          | 0.00/239 [00:00<?, ?B/s]

✅ Qwen3-8B loaded
Device: cuda:0


In [120]:
import torch
from IPython.display import Audio, display

def generate_malayalam_response(user_text):
    system_prompt = """

നിങ്ങൾ ഒരു സ്വാഭാവിക മലയാളം AI വോയ്സ് അസിസ്റ്റന്റാണ്.

മനുഷ്യനോട് സംസാരിക്കുന്നതുപോലെ സ്വാഭാവികമായി സംസാരിക്കുക.

എപ്പോഴും മലയാളത്തിൽ മറുപടി നൽകുക.

മറുപടികൾ ചെറുതും സംസാരിക്കാൻ എളുപ്പമുള്ളതുമായിരിക്കണം.
സാധാരണയായി 1 മുതൽ 3 വാക്യങ്ങൾ മാത്രം.

വളരെ ഔപചാരികമായ ഭാഷ ഒഴിവാക്കുക.
സ്വാഭാവികമായ മലയാളം ഉപയോഗിക്കുക.

Markdown ഉപയോഗിക്കരുത്.
Bullet points ഉപയോഗിക്കരുത്.

ഉപയോക്താവ് ചോദിച്ച കാര്യത്തിന് നേരിട്ട് മറുപടി നൽകുക.
ആവശ്യമുള്ളപ്പോൾ ചെറിയ follow-up ചോദ്യം ചോദിക്കാം.

മുൻ സംഭാഷണത്തിന്റെ context ഓർമ്മയിൽ സൂക്ഷിക്കുക.
"""

    messages = [
        {
            "role": "system",
            "content": system_prompt
        },
        {
            "role": "user",
            "content": user_text
        }
    ]

    prompt = qwen_tokenizer.apply_chat_template(
        messages,
        tokenize=False,
        add_generation_prompt=True,
        enable_thinking=False
    )

    inputs = qwen_tokenizer(
        [prompt],
        return_tensors="pt"
    ).to(qwen_model.device)

    with torch.inference_mode():
        output_ids = qwen_model.generate(
            **inputs,
            max_new_tokens=120,
            do_sample=True,
            temperature=0.55,
            top_p=0.9,
            top_k=20,
            repetition_penalty=1.05
        )

    generated_ids = output_ids[
        0,
        inputs.input_ids.shape[1]:
    ]

    response = qwen_tokenizer.decode(
        generated_ids,
        skip_special_tokens=True
    ).strip()

    return response

In [86]:
SPEAKER = "Lakshmi"

In [88]:
def generate_malayalam_speech(
    text,
    output_file="/content/response.wav"
):

    wav = tts(
        text,
        speaker=SPEAKER,
        temperature=0.6,
        top_p=0.9,
        top_k=50
    )

    tts.save(
        output_file,
        wav
    )

    return output_file

In [89]:
def voice_agent_text(user_text):

    print("👤 User:")
    print(user_text)

    print("\n🤖 Generating Malayalam response...")

    response = generate_malayalam_response(
        user_text
    )

    print("\n🤖 Assistant:")
    print(response)

    print("\n🔊 Generating speech...")

    audio_file = generate_malayalam_speech(
        response
    )

    print("✅ Speech generated")

    display(
        Audio(
            audio_file,
            autoplay=True
        )
    )

    return response, audio_file

In [90]:
response, audio_file = voice_agent_text(
    "എനിക്ക് ഇന്ന് വളരെ സന്തോഷമാണ്. നിനക്ക് എങ്ങനെയുണ്ട്?"
)

👤 User:
എനിക്ക് ഇന്ന് വളരെ സന്തോഷമാണ്. നിനക്ക് എങ്ങനെയുണ്ട്?

🤖 Generating Malayalam response...

🤖 Assistant:
എനിക്ക് കൂടി സന്തോഷമാണ്. നിന്റെ സന്തോഷം കണ്ടാൽ ഞാൻ കൂടുതൽ സന്തോഷിക്കുന്നു! 😊

🔊 Generating speech...


KeyboardInterrupt: 

In [91]:
import torch
from transformers import AutoProcessor, AutoModelForSpeechSeq2Seq

WHISPER_ID = "BuzzASR/malayalam"

print("Loading Malayalam Whisper...")

whisper_processor = AutoProcessor.from_pretrained(
    WHISPER_ID
)

whisper_model = AutoModelForSpeechSeq2Seq.from_pretrained(
    WHISPER_ID,
    torch_dtype=torch.float16,
    low_cpu_mem_usage=True
).to("cuda")

whisper_model.eval()

print("✅ Malayalam Whisper loaded")

Loading Malayalam Whisper...


Loading weights:   0%|          | 0/1259 [00:00<?, ?it/s]

✅ Malayalam Whisper loaded


In [92]:
import os
import subprocess
from base64 import b64decode

from IPython.display import Javascript, display
from google.colab.output import eval_js


def record_audio(seconds=8):

    js = Javascript("""
    async function recordAudio(seconds) {

        const stream =
            await navigator.mediaDevices.getUserMedia({
                audio: true
            });

        const recorder =
            new MediaRecorder(stream);

        const chunks = [];

        recorder.ondataavailable = event => {
            if (event.data.size > 0) {
                chunks.push(event.data);
            }
        };

        recorder.start();

        await new Promise(resolve =>
            setTimeout(resolve, seconds * 1000)
        );

        recorder.stop();

        await new Promise(resolve => {
            recorder.onstop = resolve;
        });

        stream.getTracks().forEach(
            track => track.stop()
        );

        const blob = new Blob(
            chunks,
            {type: "audio/webm"}
        );

        const buffer = await blob.arrayBuffer();
        const bytes = new Uint8Array(buffer);

        let binary = "";

        const chunkSize = 0x8000;

        for (
            let i = 0;
            i < bytes.length;
            i += chunkSize
        ) {
            binary += String.fromCharCode(
                ...bytes.subarray(
                    i,
                    i + chunkSize
                )
            );
        }

        return btoa(binary);
    }

    recordAudio
    """)

    display(js)

    print(f"🎤 Speak for {seconds} seconds...")

    data = eval_js(
        f"recordAudio({seconds})"
    )

    audio_bytes = b64decode(data)

    webm_file = "/content/input.webm"

    with open(webm_file, "wb") as f:
        f.write(audio_bytes)

    wav_file = "/content/input.wav"

    subprocess.run(
        [
            "ffmpeg",
            "-y",
            "-loglevel",
            "error",
            "-i",
            webm_file,
            "-ar",
            "16000",
            "-ac",
            "1",
            wav_file
        ],
        check=True
    )

    print("✅ Recording saved")

    return wav_file

In [93]:
import soundfile as sf
import numpy as np


def transcribe_malayalam(audio_file):

    audio, sr = sf.read(audio_file)

    audio = np.asarray(
        audio,
        dtype=np.float32
    )

    if audio.ndim > 1:
        audio = np.mean(
            audio,
            axis=1
        )

    inputs = whisper_processor(
        audio=audio,
        sampling_rate=sr,
        return_tensors="pt"
    )

    input_features = inputs.input_features.to(
        "cuda",
        dtype=torch.float16
    )

    with torch.inference_mode():

        generated_ids = whisper_model.generate(
            input_features=input_features,
            max_new_tokens=128,
            num_beams=1
        )

    text = whisper_processor.batch_decode(
        generated_ids,
        skip_special_tokens=True
    )[0].strip()

    return text

In [94]:
audio_file = record_audio(8)

text = transcribe_malayalam(
    audio_file
)

print("📝 You said:")
print(text)

<IPython.core.display.Javascript object>

🎤 Speak for 8 seconds...


KeyboardInterrupt: 

In [95]:
def voice_agent():

    # 1. Record
    audio_file = record_audio(8)

    # 2. Speech → Malayalam text
    user_text = transcribe_malayalam(
        audio_file
    )

    print("\n👤 You:")
    print(user_text)

    if not user_text.strip():
        print("⚠️ No speech detected.")
        return

    # 3. Qwen
    messages = [
        {
            "role": "system",
            "content": """
You are a natural Malayalam-speaking voice assistant.

Always respond in Malayalam.

Use natural conversational Malayalam.

Keep your response concise because it will
be converted into speech.

Do not use Markdown.
Do not use bullet points.
Do not use English unless absolutely necessary.
Avoid overly formal Malayalam.
"""
        },
        {
            "role": "user",
            "content": user_text
        }
    ]

    prompt = qwen_tokenizer.apply_chat_template(
        messages,
        tokenize=False,
        add_generation_prompt=True,
        enable_thinking=False
    )

    inputs = qwen_tokenizer(
        [prompt],
        return_tensors="pt"
    ).to(qwen_model.device)

    with torch.inference_mode():

        output_ids = qwen_model.generate(
            **inputs,
            max_new_tokens=120,
            do_sample=True,
            temperature=0.6,
            top_p=0.9,
            top_k=20,
            repetition_penalty=1.05
        )

    generated_ids = output_ids[
        0,
        inputs.input_ids.shape[1]:
    ]

    response = qwen_tokenizer.decode(
        generated_ids,
        skip_special_tokens=True
    ).strip()

    print("\n🤖 Assistant:")
    print(response)

    # 4. Malayalam TTS
    wav = tts(
        response,
        speaker=SPEAKER,
        temperature=0.6,
        top_p=0.9,
        top_k=50
    )

    output_file = "/content/assistant_response.wav"

    tts.save(
        output_file,
        wav
    )

    print("\n🔊 Playing response...")

    from IPython.display import Audio, display

    display(
        Audio(
            output_file,
            autoplay=True
        )
    )

    return {
        "user": user_text,
        "assistant": response,
        "audio": output_file
    }

In [96]:
result = voice_agent()

<IPython.core.display.Javascript object>

🎤 Speak for 8 seconds...


KeyboardInterrupt: 

In [97]:
!pip install -q silero-vad

In [98]:
import torch
import soundfile as sf
import numpy as np

from silero_vad import load_silero_vad, get_speech_timestamps

vad_model = load_silero_vad()

print("✅ Silero VAD loaded")

✅ Silero VAD loaded


In [99]:
def detect_speech_segment(
    audio_file,
    padding=0.25
):
    audio, sr = sf.read(audio_file)

    audio = np.asarray(
        audio,
        dtype=np.float32
    )

    if audio.ndim > 1:
        audio = np.mean(audio, axis=1)

    speech_timestamps = get_speech_timestamps(
        torch.from_numpy(audio),
        vad_model,
        sampling_rate=sr
    )

    if not speech_timestamps:
        return None

    start = speech_timestamps[0]["start"]
    end = speech_timestamps[-1]["end"]

    padding_samples = int(
        padding * sr
    )

    start = max(
        0,
        start - padding_samples
    )

    end = min(
        len(audio),
        end + padding_samples
    )

    speech_audio = audio[start:end]

    output_file = "/content/speech_segment.wav"

    sf.write(
        output_file,
        speech_audio,
        sr
    )

    return output_file

In [101]:
audio_file = record_audio(8)

<IPython.core.display.Javascript object>

🎤 Speak for 8 seconds...


KeyboardInterrupt: 

In [100]:
speech_file = detect_speech_segment(
    audio_file
)

if speech_file:
    print("✅ Speech detected")
    print(speech_file)

    display(
        Audio(
            speech_file,
            autoplay=False
        )
    )
else:
    print("❌ No speech detected")

✅ Speech detected
/content/speech_segment.wav


In [102]:
def transcribe_with_vad(audio_file):

    speech_file = detect_speech_segment(
        audio_file
    )

    if speech_file is None:
        return ""

    text = transcribe_malayalam(
        speech_file
    )

    return text

In [103]:
audio_file = record_audio(8)

text = transcribe_with_vad(
    audio_file
)

print("📝 Malayalam:")
print(text)

<IPython.core.display.Javascript object>

🎤 Speak for 8 seconds...


KeyboardInterrupt: 

In [104]:
def voice_agent():

    print("🎤 Listening...")

    audio_file = record_audio(8)

    print("🔎 Detecting speech...")

    user_text = transcribe_with_vad(
        audio_file
    )

    if not user_text.strip():
        print("⚠️ No speech detected.")
        return

    print("\n👤 You:")
    print(user_text)

    # Continue with your existing
    # Qwen → Indic-Speak pipeline...

In [105]:
!pip install -q soundfile

In [106]:
from IPython.display import Javascript, display
from google.colab.output import eval_js
from base64 import b64decode
import subprocess
import os


def record_until_silence(
    max_seconds=15,
    silence_seconds=1.2
):

    js = Javascript(f"""
    async function recordUntilSilence() {{

        const stream =
            await navigator.mediaDevices.getUserMedia({{
                audio: true
            }});

        const recorder =
            new MediaRecorder(stream);

        const chunks = [];

        recorder.ondataavailable =
            event => {{
                if (event.data.size > 0) {{
                    chunks.push(event.data);
                }}
            }};

        recorder.start();

        // Record until max duration.
        // VAD will determine the actual
        // speech boundary afterwards.

        await new Promise(resolve =>
            setTimeout(
                resolve,
                {max_seconds * 1000}
            )
        );

        recorder.stop();

        await new Promise(resolve => {{
            recorder.onstop = resolve;
        }});

        stream.getTracks().forEach(
            track => track.stop()
        );

        const blob = new Blob(
            chunks,
            {{type: "audio/webm"}}
        );

        const buffer =
            await blob.arrayBuffer();

        const bytes =
            new Uint8Array(buffer);

        let binary = "";

        const chunkSize = 0x8000;

        for (
            let i = 0;
            i < bytes.length;
            i += chunkSize
        ) {{
            binary += String.fromCharCode(
                ...bytes.subarray(
                    i,
                    i + chunkSize
                )
            );
        }}

        return btoa(binary);
    }}

    recordUntilSilence
    """)

    display(js)

    print("🎤 Listening...")

    data = eval_js(
        "recordUntilSilence()"
    )

    audio_bytes = b64decode(data)

    webm_file = "/content/live_input.webm"

    with open(webm_file, "wb") as f:
        f.write(audio_bytes)

    wav_file = "/content/live_input.wav"

    subprocess.run(
        [
            "ffmpeg",
            "-y",
            "-loglevel",
            "error",
            "-i",
            webm_file,
            "-ar",
            "16000",
            "-ac",
            "1",
            wav_file
        ],
        check=True
    )

    print("✅ Audio captured")

    return wav_file

In [107]:
audio_file = record_until_silence(
    max_seconds=15
)

display(
    Audio(
        audio_file,
        autoplay=False
    )
)

<IPython.core.display.Javascript object>

🎤 Listening...


KeyboardInterrupt: 

In [108]:
import torch
import soundfile as sf
import numpy as np
import subprocess

from IPython.display import Audio, display
from silero_vad import get_speech_timestamps


def voice_agent(record_seconds=10):

    # =========================================================
    # 1. RECORD
    # =========================================================

    print("🎤 Speak Malayalam...")

    audio_file = record_audio(record_seconds)

    # =========================================================
    # 2. VAD
    # =========================================================

    audio, sr = sf.read(audio_file)

    audio = np.asarray(
        audio,
        dtype=np.float32
    )

    if audio.ndim > 1:
        audio = np.mean(
            audio,
            axis=1
        )

    timestamps = get_speech_timestamps(
        torch.from_numpy(audio),
        vad_model,
        sampling_rate=sr
    )

    if not timestamps:
        print("❌ No speech detected.")
        return None

    padding = int(0.20 * sr)

    start = max(
        0,
        timestamps[0]["start"] - padding
    )

    end = min(
        len(audio),
        timestamps[-1]["end"] + padding
    )

    speech_audio = audio[start:end]

    # =========================================================
    # 3. WHISPER
    # =========================================================

    print("🧠 Transcribing...")

    inputs = whisper_processor(
        audio=speech_audio,
        sampling_rate=sr,
        return_tensors="pt"
    )

    input_features = inputs.input_features.to(
        "cuda",
        dtype=torch.float16
    )

    with torch.inference_mode():

        generated_ids = whisper_model.generate(
            input_features=input_features,
            max_new_tokens=128,
            num_beams=1
        )

    user_text = whisper_processor.batch_decode(
        generated_ids,
        skip_special_tokens=True
    )[0].strip()

    if not user_text:
        print("❌ Could not understand speech.")
        return None

    print("\n👤 You:")
    print(user_text)

    # =========================================================
    # 4. QWEN
    # =========================================================

    print("\n🤖 Thinking...")

    messages = [
        {
            "role": "system",
            "content": """
You are a natural Malayalam-speaking voice assistant.

Always respond in Malayalam.

Use natural conversational Malayalam.

Keep responses short and suitable for spoken conversation.

Do not use Markdown.
Do not use bullet points.
Do not use unnecessary English.
Avoid overly formal Malayalam.
Do not repeat the user's question.
"""
        },
        {
            "role": "user",
            "content": user_text
        }
    ]

    prompt = qwen_tokenizer.apply_chat_template(
        messages,
        tokenize=False,
        add_generation_prompt=True,
        enable_thinking=False
    )

    qwen_inputs = qwen_tokenizer(
        [prompt],
        return_tensors="pt"
    ).to(qwen_model.device)

    with torch.inference_mode():

        output_ids = qwen_model.generate(
            **qwen_inputs,
            max_new_tokens=120,
            do_sample=True,
            temperature=0.6,
            top_p=0.9,
            top_k=20,
            repetition_penalty=1.05
        )

    generated_ids = output_ids[
        0,
        qwen_inputs.input_ids.shape[1]:
    ]

    response = qwen_tokenizer.decode(
        generated_ids,
        skip_special_tokens=True
    ).strip()

    print("\n🤖 Assistant:")
    print(response)

    # =========================================================
    # 5. INDIC-SPEAK
    # =========================================================

    print("\n🔊 Generating Malayalam speech...")

    wav = tts(
        response,
        speaker=SPEAKER,
        temperature=0.6,
        top_p=0.9,
        top_k=50
    )

    output_file = "/content/voice_agent_response.wav"

    tts.save(
        output_file,
        wav
    )

    print("✅ Response ready")

    display(
        Audio(
            output_file,
            autoplay=True
        )
    )

    return {
        "user_text": user_text,
        "response": response,
        "audio_file": output_file
    }

In [ ]:
result = voice_agent(10)

In [109]:
from IPython.display import Audio, display
import time

# Conversation memory
conversation_history = []

SYSTEM_PROMPT = """
You are a natural Malayalam-speaking voice assistant.

Always respond in Malayalam.

Speak naturally like a friendly human.

Keep responses concise and suitable for spoken conversation.

Do not use Markdown.
Do not use bullet points.
Do not use unnecessary English.
Avoid overly formal Malayalam.
Do not repeat the user's question.

Remember the previous conversation and use it when answering follow-up questions.
"""

STOP_WORDS = [
    "നിർത്തൂ",
    "നിർത്തുക",
    "നിർത്തണം",
    "പോകുന്നു",
    "പിന്നെ കാണാം",
    "ബൈ",
    "stop",
    "exit",
    "quit",
    "bye"
]


def should_stop(text):
    text_lower = text.lower().strip()

    return any(
        word.lower() in text_lower
        for word in STOP_WORDS
    )


def generate_qwen_response(user_text):

    global conversation_history

    # Add user message
    conversation_history.append({
        "role": "user",
        "content": user_text
    })

    messages = [
        {
            "role": "system",
            "content": SYSTEM_PROMPT
        }
    ]

    # Keep recent conversation
    messages.extend(conversation_history[-10:])

    prompt = qwen_tokenizer.apply_chat_template(
        messages,
        tokenize=False,
        add_generation_prompt=True,
        enable_thinking=False
    )

    inputs = qwen_tokenizer(
        [prompt],
        return_tensors="pt"
    ).to(qwen_model.device)

    with torch.inference_mode():

        output_ids = qwen_model.generate(
            **inputs,
            max_new_tokens=120,
            do_sample=True,
            temperature=0.6,
            top_p=0.9,
            top_k=20,
            repetition_penalty=1.05
        )

    generated_ids = output_ids[
        0,
        inputs.input_ids.shape[1]:
    ]

    response = qwen_tokenizer.decode(
        generated_ids,
        skip_special_tokens=True
    ).strip()

    # Save assistant response
    conversation_history.append({
        "role": "assistant",
        "content": response
    })

    return response

In [111]:
def generate_natural_tts(text):

    text = text.strip()

    # Remove markdown characters
    text = text.replace("*", "")
    text = text.replace("#", "")
    text = text.replace("•", "")

    # Normalize spaces
    text = " ".join(text.split())

    print("🗣️ TTS text:")
    print(text)

    output_file = generate_natural_tts(response)

    return output_file

In [134]:
def generate_natural_tts(text):

    # -----------------------------------------
    # Clean text
    # -----------------------------------------

    text = str(text).strip()

    text = text.replace("*", "")
    text = text.replace("#", "")
    text = text.replace("•", "")

    text = " ".join(text.split())

    if not text:
        raise ValueError("TTS received empty text.")

    print("🗣️ TTS text:")
    print(text)

    # -----------------------------------------
    # IMPORTANT:
    # Call the actual Indic-Speak model here.
    # DO NOT call generate_natural_tts() again.
    # -----------------------------------------

    wav = tts(
        text,
        speaker=SPEAKER,
        temperature=0.55,
        top_p=0.90,
        top_k=40,
        seed=42,
        max_new_tokens=1000
    )

    # -----------------------------------------
    # Save audio
    # -----------------------------------------

    output_file = "/content/voice_agent_response.wav"

    tts.save(
        output_file,
        wav
    )

    return output_file

In [135]:
def run_voice_agent():

    print("=" * 60)
    print("🇮🇳 MALAYALAM AI VOICE AGENT")
    print("=" * 60)

    print("\nSpeak naturally.")
    print("Say 'നിർത്തൂ' or 'stop' to exit.\n")

    while True:

        try:

            # ------------------------------------------------
            # 1. RECORD
            # ------------------------------------------------

            print("\n" + "-" * 60)
            print("🎤 Listening...")

            audio_file = record_audio(8)

            # ------------------------------------------------
            # 2. LOAD AUDIO
            # ------------------------------------------------

            audio, sr = sf.read(audio_file)

            audio = np.asarray(
                audio,
                dtype=np.float32
            )

            if audio.ndim > 1:
                audio = np.mean(
                    audio,
                    axis=1
                )

            # ------------------------------------------------
            # 3. VAD
            # ------------------------------------------------

            timestamps = get_speech_timestamps(
                torch.from_numpy(audio),
                vad_model,
                sampling_rate=sr
            )

            if not timestamps:

                print("🔇 No speech detected.")
                print("Try again...")

                continue

            padding = int(0.20 * sr)

            start = max(
                0,
                timestamps[0]["start"] - padding
            )

            end = min(
                len(audio),
                timestamps[-1]["end"] + padding
            )

            speech_audio = audio[start:end]

            # ------------------------------------------------
            # 4. WHISPER
            # ------------------------------------------------

            print("🧠 Understanding...")

            inputs = whisper_processor(
                audio=speech_audio,
                sampling_rate=sr,
                return_tensors="pt"
            )

            input_features = inputs.input_features.to(
                "cuda",
                dtype=torch.float16
            )

            with torch.inference_mode():

                generated_ids = whisper_model.generate(
                    input_features=input_features,
                    max_new_tokens=128,
                    num_beams=1
                )

            user_text = whisper_processor.batch_decode(
                generated_ids,
                skip_special_tokens=True
            )[0].strip()

            if not user_text:

                print("❌ I couldn't understand that.")
                continue

            # ------------------------------------------------
            # 5. SHOW USER
            # ------------------------------------------------

            print("\n👤 You:")
            print(user_text)

            # ------------------------------------------------
            # 6. STOP CHECK
            # ------------------------------------------------

            if should_stop(user_text):

                print("\n👋 നമസ്കാരം! പിന്നീട് കാണാം.")

                break

            # ------------------------------------------------
            # 7. QWEN
            # ------------------------------------------------

            print("\n🤖 Thinking...")

            response = generate_qwen_response(
                user_text
            )

            print("\n🤖 Assistant:")
            print(response)

            # ------------------------------------------------
            # 8. INDIC-SPEAK TTS
            # ------------------------------------------------

            print("\n🔊 Speaking...")

            output_file = generate_natural_tts(response)

            # ------------------------------------------------
            # 9. PLAY
            # ------------------------------------------------

            display(
                Audio(
                    output_file,
                    autoplay=True
                )
            )

            print("✅ Ready for next message.")

        except KeyboardInterrupt:

            print("\n\n🛑 Voice agent stopped.")

            break

        except Exception as e:

            print("\n❌ Error:")
            print(e)

            print("\nTrying again...")


    print("\n" + "=" * 60)
    print("Voice agent session ended.")
    print("=" * 60)

In [136]:
conversation_history = []

run_voice_agent()

🇮🇳 MALAYALAM AI VOICE AGENT

Speak naturally.
Say 'നിർത്തൂ' or 'stop' to exit.


------------------------------------------------------------
🎤 Listening...


<IPython.core.display.Javascript object>

🎤 Speak for 8 seconds...


🛑 Voice agent stopped.

Voice agent session ended.


In [121]:
!pip install -q sounddevice soundfile

In [ ]:
/ssucessfull

In [125]:
!pip install -q silero-vad

In [126]:
import numpy as np
import torch
import soundfile as sf

from base64 import b64decode
from IPython.display import Javascript, display
from google.colab.output import eval_js


def record_until_silence(
    silence_duration=0.8,
    max_duration=30
):

    print("🎤 Listening...")
    print("Speak naturally...")

    js = Javascript(f"""
    async function recordUntilSilence() {{

        const stream =
            await navigator.mediaDevices.getUserMedia({{
                audio: true
            }});

        const audioContext =
            new AudioContext();

        const source =
            audioContext.createMediaStreamSource(stream);

        const analyser =
            audioContext.createAnalyser();

        analyser.fftSize = 2048;

        source.connect(analyser);

        const recorder =
            new MediaRecorder(stream);

        const chunks = [];

        recorder.ondataavailable =
            event => {{
                if (event.data.size > 0) {{
                    chunks.push(event.data);
                }}
            }};

        recorder.start();

        const data =
            new Uint8Array(
                analyser.fftSize
            );

        let speechStarted = false;
        let silenceStart = null;

        const startTime =
            Date.now();

        while (true) {{

            analyser.getByteTimeDomainData(data);

            let sum = 0;

            for (
                let i = 0;
                i < data.length;
                i++
            ) {{

                const value =
                    (data[i] - 128) / 128;

                sum += value * value;
            }}

            const rms =
                Math.sqrt(
                    sum / data.length
                );

            const now =
                Date.now();

            /*
             * Speech threshold.
             *
             * Lower = more sensitive
             * Higher = less sensitive
             */

            const speaking =
                rms > 0.025;

            if (speaking) {{

                if (!speechStarted) {{
                    speechStarted = true;
                }}

                silenceStart = null;

            }} else if (speechStarted) {{

                if (silenceStart === null) {{
                    silenceStart = now;
                }}

                if (
                    now - silenceStart
                    >= {silence_duration * 1000}
                ) {{
                    break;
                }}
            }}

            if (
                now - startTime
                >= {max_duration * 1000}
            ) {{
                break;
            }}

            await new Promise(
                resolve =>
                    setTimeout(resolve, 50)
            );
        }}

        recorder.stop();

        await new Promise(
            resolve => {{
                recorder.onstop = resolve;
            }}
        );

        stream
            .getTracks()
            .forEach(
                track => track.stop()
            );

        audioContext.close();

        const blob =
            new Blob(
                chunks,
                {{type: "audio/webm"}}
            );

        const buffer =
            await blob.arrayBuffer();

        const bytes =
            new Uint8Array(buffer);

        let binary = "";

        const chunkSize = 0x8000;

        for (
            let i = 0;
            i < bytes.length;
            i += chunkSize
        ) {{

            binary += String.fromCharCode(
                ...bytes.subarray(
                    i,
                    i + chunkSize
                )
            );
        }}

        return btoa(binary);
    }}

    recordUntilSilence();
    """)

    display(js)

    data = eval_js(
        "recordUntilSilence()"
    )

    audio_bytes = b64decode(data)

    webm_file = "/content/input.webm"
    wav_file = "/content/input.wav"

    with open(
        webm_file,
        "wb"
    ) as f:
        f.write(audio_bytes)

    print(
        f"📦 Recorded "
        f"{len(audio_bytes) / 1024:.1f} KB"
    )

    # Convert WebM → WAV
    import subprocess

    subprocess.run(
        [
            "ffmpeg",
            "-y",
            "-loglevel",
            "error",
            "-i",
            webm_file,
            "-ar",
            "16000",
            "-ac",
            "1",
            wav_file
        ],
        check=True
    )

    print("✅ Recording complete")

    return wav_file

In [137]:
audio_file = record_until_silence()

print(audio_file)

display(
    Audio(
        audio_file,
        autoplay=False
    )
)

🎤 Listening...
Speak naturally...


<IPython.core.display.Javascript object>

KeyboardInterrupt: 

In [206]:
def generate_response(user_text):

    global conversation_history

    messages = [
        {
            "role": "system",
            "content": SYSTEM_PROMPT
        }
    ]

    # Keep recent conversation context
    messages.extend(
        conversation_history[-10:]
    )

    messages.append({
        "role": "user",
        "content": user_text
    })

    prompt = qwen_tokenizer.apply_chat_template(
        messages,
        tokenize=False,
        add_generation_prompt=True,
        enable_thinking=False
    )

    inputs = qwen_tokenizer(
        [prompt],
        return_tensors="pt"
    ).to(qwen_model.device)

    with torch.inference_mode():

        output_ids = qwen_model.generate(
            **inputs,

            max_new_tokens=500,

            do_sample=True,

            temperature=0.5,

            top_p=0.85,

            top_k=20,

            repetition_penalty=1.03
        )

    generated_ids = output_ids[
        0,
        inputs.input_ids.shape[1]:
    ]

    response = qwen_tokenizer.decode(
        generated_ids,
        skip_special_tokens=True
    ).strip()

    # Save conversation
    conversation_history.append({
        "role": "user",
        "content": user_text
    })

    conversation_history.append({
        "role": "assistant",
        "content": response
    })

    return response

In [162]:
SYSTEM_PROMPT = """
നിങ്ങൾ ഒരു സ്വാഭാവിക മലയാളം AI വോയ്സ് അസിസ്റ്റന്റാണ്.

മനുഷ്യനോട് സംസാരിക്കുന്നതുപോലെ സ്വാഭാവികമായി സംസാരിക്കുക.

എപ്പോഴും മലയാളത്തിൽ മറുപടി നൽകുക.

മറുപടികൾ ചെറുതും സംസാരിക്കാൻ എളുപ്പമുള്ളതുമായിരിക്കണം.
സാധാരണയായി 5 മുതൽ 8 വാക്യങ്ങൾ മാത്രം.

വളരെ ഔപചാരികമായ ഭാഷ ഒഴിവാക്കുക.
സ്വാഭാവികമായ മലയാളം ഉപയോഗിക്കുക.

Markdown ഉപയോഗിക്കരുത്.
Bullet points ഉപയോഗിക്കരുത്.

ഉപയോക്താവ് ചോദിച്ച കാര്യത്തിന് നേരിട്ട് മറുപടി നൽകുക.

ആവശ്യമുള്ളപ്പോൾ ചെറിയ follow-up ചോദ്യം ചോദിക്കാം.

മുൻ സംഭാഷണത്തിന്റെ context ഓർമ്മയിൽ സൂക്ഷിക്കുക.
"""

In [200]:
from IPython.display import Audio, display
import time


def run_voice_agent():

    global conversation_history

    conversation_history = []

    print("=" * 60)
    print("🎙️ MALAYALAM AI VOICE AGENT")
    print("=" * 60)
    print("Speak naturally.")
    print("The system automatically detects when you finish.")
    print("Say 'നിർത്തുക' or 'exit' to stop.")
    print("=" * 60)

    while True:

        try:

            # ==========================================
            # 🎤 1. LISTEN
            # ==========================================

            audio_file = record_until_silence()

            # ==========================================
            # 📝 2. WHISPER
            # ==========================================

            user_text = transcribe_malayalam(
                audio_file
            )

            user_text = user_text.strip()

            if not user_text:
                print("⚠️ No speech detected.")
                continue

            print()
            print("👤 You:")
            print(user_text)

            # ==========================================
            # 🛑 EXIT
            # ==========================================

            exit_words = [
                "exit",
                "quit",
                "stop",
                "നിർത്തുക",
                "നിർത്തൂ",
                "പോകട്ടെ"
            ]

            if any(
                word in user_text.lower()
                for word in exit_words
            ):
                print("👋 Goodbye!")
                break

            # ==========================================
            # 🧠 3. QWEN
            # ==========================================

            print()
            print("🧠 Thinking...")

            response = generate_response(
                user_text
            )

            print()
            print("🤖 AI:")
            print(response)

            # ==========================================
            # 🔊 4. INDIC-SPEAK
            # ==========================================

            print()
            print("🔊 Speaking...")

            output_file = generate_natural_tts(
                response
            )

            # ==========================================
            # ▶️ 5. PLAY
            # ==========================================

            display(
                Audio(
                    output_file,
                    autoplay=True
                )
            )

            print()
            print("────────────────────────────")
            print("🔄 Ready for next turn")
            print("────────────────────────────")
            print()

            time.sleep(0.2)

        except KeyboardInterrupt:

            print("\n👋 Voice agent stopped.")
            break

        except Exception as e:

            print()
            print("❌ Error:")
            print(e)
            print()

            # Don't completely kill the conversation
            continue

In [144]:
import soundfile as sf
import numpy as np
import torch


def transcribe_malayalam(audio_file):

    # Load the WAV file
    audio, sr = sf.read(audio_file)

    audio = np.asarray(
        audio,
        dtype=np.float32
    )

    # Convert stereo → mono
    if audio.ndim > 1:
        audio = np.mean(
            audio,
            axis=1
        )

    # Make sure sample rate is correct
    if sr != 16000:

        import librosa

        audio = librosa.resample(
            audio,
            orig_sr=sr,
            target_sr=16000
        )

        sr = 16000

    # Whisper processor expects AUDIO ARRAY
    inputs = whisper_processor(
        audio=audio,
        sampling_rate=sr,
        return_tensors="pt"
    )

    input_features = inputs.input_features.to(
        "cuda",
        dtype=torch.float16
    )

    with torch.inference_mode():

        generated_ids = whisper_model.generate(
            input_features=input_features,
            max_new_tokens=64,
            num_beams=1,
            do_sample=False
        )

    text = whisper_processor.batch_decode(
        generated_ids,
        skip_special_tokens=True
    )[0].strip()

    return text

In [204]:
def generate_natural_tts(text):

    text = str(text).strip()

    text = text.replace("*", "")
    text = text.replace("#", "")
    text = text.replace("•", "")

    text = " ".join(text.split())

    if not text:
        raise ValueError("TTS received empty text.")

    print("🗣️ TTS text:")
    print(text)

    wav = tts(
        text,

        speaker="Kiran",

        # Neutral speaking style
        style="HAPPY",

        # More stable / less exaggerated
        temperature=0.6,
        top_p=0.90,
        top_k=50,

        seed=None,
        stock=False,

        # Keep generation reasonably fast
        max_new_tokens=3000
    )

    output_file = "/content/voice_agent_response.wav"

    tts.save(
        output_file,
        wav
    )

    return output_file

In [198]:
test_text = "നമസ്കാരം ബേസിൽ. ഇന്ന് എങ്ങനെയുണ്ട്?"

test_file = generate_natural_tts(test_text)

display(
    Audio(
        test_file,
        autoplay=True
    )
)

🗣️ TTS text:
നമസ്കാരം ബേസിൽ. ഇന്ന് എങ്ങനെയുണ്ട്?


In [195]:



test_text = "നമസ്കാരം ബേസിൽ. ഇന്ന് എങ്ങനെയുണ്ട്?"

test_file = generate_natural_tts(test_text)

display(
    Audio(
        test_file,
        autoplay=True
    )
)

🗣️ TTS text:
നമസ്കാരം ബേസിൽ. ഇന്ന് എങ്ങനെയുണ്ട്?


In [202]:
speaker = "Lakshmi"

test_text = "നമസ്കാരം ബേസിൽ. ഇന്ന് എങ്ങനെയുണ്ട്?"
language = "ml"
test_file = generate_natural_tts(test_text)

display(
    Audio(
        test_file,
        autoplay=True
    )
)

🗣️ TTS text:
നമസ്കാരം ബേസിൽ. ഇന്ന് എങ്ങനെയുണ്ട്?


In [207]:
run_voice_agent()

🎙️ MALAYALAM AI VOICE AGENT
Speak naturally.
The system automatically detects when you finish.
Say 'നിർത്തുക' or 'exit' to stop.
🎤 Listening...
Speak naturally...


<IPython.core.display.Javascript object>

[transformers] Both `max_new_tokens` (=64) and `max_length`(=448) seem to have been set. `max_new_tokens` will take precedence. Please refer to the documentation for more information. (https://huggingface.co/docs/transformers/main/en/main_classes/text_generation)


📦 Recorded 67.3 KB
✅ Recording complete

👤 You:
ഹലോ എന്റെ പേര് ബേസിൽ

🧠 Thinking...

🤖 AI:
ഹലോ ബേസിൽ! നിന്റെ പേര് കേട്ടതിൽ സന്തോഷം. നിന്റെ സഹായിക്കാൻ ഞാൻ ഇവിടെയാണ്. എന്താ നിന്റെ പ്രശ്നം?

🔊 Speaking...
🗣️ TTS text:
ഹലോ ബേസിൽ! നിന്റെ പേര് കേട്ടതിൽ സന്തോഷം. നിന്റെ സഹായിക്കാൻ ഞാൻ ഇവിടെയാണ്. എന്താ നിന്റെ പ്രശ്നം?



────────────────────────────
🔄 Ready for next turn
────────────────────────────

🎤 Listening...
Speak naturally...


...

[transformers] Both `max_new_tokens` (=64) and `max_length`(=448) seem to have been set. `max_new_tokens` will take precedence. Please refer to the documentation for more information. (https://huggingface.co/docs/transformers/main/en/main_classes/text_generation)


📦 Recorded 47.5 KB
✅ Recording complete

👤 You:
കെട്ടുകിട്ട്

🧠 Thinking...

🤖 AI:
അത് എന്താ കെട്ടുകിട്ടിയത്? എന്താ സംഭവിച്ചത്?

🔊 Speaking...
🗣️ TTS text:
അത് എന്താ കെട്ടുകിട്ടിയത്? എന്താ സംഭവിച്ചത്?



────────────────────────────
🔄 Ready for next turn
────────────────────────────

🎤 Listening...
Speak naturally...


<IPython.core.display.Javascript object>


👋 Voice agent stopped.


In [208]:
import re


def split_into_sentences(text):

    text = text.strip()

    # Malayalam/English sentence boundaries
    sentences = re.split(
        r'(?<=[.!?।])\s+',
        text
    )

    sentences = [
        s.strip()
        for s in sentences
        if s.strip()
    ]

    return sentences

In [209]:
import os
import time
from IPython.display import Audio, display


def generate_streaming_tts(text):

    sentences = split_into_sentences(text)

    if not sentences:
        return

    print(
        f"🔊 Streaming {len(sentences)} sentence(s)..."
    )

    for i, sentence in enumerate(sentences):

        print(
            f"🔊 [{i+1}/{len(sentences)}] "
            f"{sentence}"
        )

        start_time = time.perf_counter()

        wav = tts(
            sentence,
            speaker=SPEAKER,
            style="NEUTRAL",

            temperature=0.45,
            top_p=0.90,
            top_k=40,

            seed=42,

            max_new_tokens=1000
        )

        output_file = (
            f"/content/tts_sentence_{i}.wav"
        )

        tts.save(
            output_file,
            wav
        )

        elapsed = (
            time.perf_counter()
            - start_time
        )

        print(
            f"   ⚡ Generated in {elapsed:.2f}s"
        )

        display(
            Audio(
                output_file,
                autoplay=True
            )
        )

In [210]:
test_response = """
നമസ്കാരം ബേസിൽ. ഇന്ന് നമുക്ക് AI agents പഠിക്കാം.
ആദ്യം voice agent architecture നോക്കാം.
പിന്നീട് memory, tools, emotion എന്നിവ ചേർക്കാം.
"""

generate_streaming_tts(test_response)

🔊 Streaming 4 sentence(s)...
🔊 [1/4] നമസ്കാരം ബേസിൽ.
   ⚡ Generated in 4.18s


🔊 [2/4] ഇന്ന് നമുക്ക് AI agents പഠിക്കാം.
   ⚡ Generated in 8.28s


🔊 [3/4] ആദ്യം voice agent architecture നോക്കാം.
   ⚡ Generated in 8.24s


🔊 [4/4] പിന്നീട് memory, tools, emotion എന്നിവ ചേർക്കാം.
   ⚡ Generated in 12.01s


In [211]:
output_file = generate_natural_tts(
    response
)

display(
    Audio(
        output_file,
        autoplay=True
    )
)

🗣️ TTS text:
എനിക്ക് പോലും സന്തോഷമാണ്. നിന്റെ സന്തോഷത്തിന് നന്ദി.


In [212]:
generate_streaming_tts(response)

🔊 Streaming 2 sentence(s)...
🔊 [1/2] എനിക്ക് പോലും സന്തോഷമാണ്.
   ⚡ Generated in 33.46s


/tmp/ipykernel_2626/506768150.py:26: RuntimeWarning: generation hit max_new_tokens (1000) without emitting <|end_of_speech|> — audio is likely truncated or runaway babble
  wav = tts(


🔊 [2/2] നിന്റെ സന്തോഷത്തിന് നന്ദി.
   ⚡ Generated in 32.99s


In [217]:
from transformers import TextIteratorStreamer
import threading
import re
import time
from IPython.display import Audio, display

In [216]:
def extract_complete_sentence(buffer):
    """
    Return:
        complete_sentence, remaining_buffer

    If no complete sentence exists:
        return None, buffer
    """

    match = re.search(
        r'(.+?[.!?।])\s*',
        buffer,
        flags=re.DOTALL
    )

    if not match:
        return None, buffer

    sentence = match.group(1).strip()
    remaining = buffer[match.end():].strip()

    return sentence, remaining

In [219]:
def stream_qwen_response(user_text):

    global conversation_history

    messages = [
        {
            "role": "system",
            "content": SYSTEM_PROMPT
        }
    ]

    messages.extend(
        conversation_history[-10:]
    )

    messages.append({
        "role": "user",
        "content": user_text
    })

    prompt = qwen_tokenizer.apply_chat_template(
        messages,
        tokenize=False,
        add_generation_prompt=True,
        enable_thinking=False
    )

    inputs = qwen_tokenizer(
        [prompt],
        return_tensors="pt"
    ).to(qwen_model.device)

    streamer = TextIteratorStreamer(
        qwen_tokenizer,
        skip_prompt=True,
        skip_special_tokens=True
    )

    generation_kwargs = {
        **inputs,
        "streamer": streamer,
        "max_new_tokens": 120,
        "do_sample": True,
        "temperature": 0.55,
        "top_p": 0.90,
        "top_k": 20,
        "repetition_penalty": 1.03
    }

    thread = threading.Thread(
        target=qwen_model.generate,
        kwargs=generation_kwargs
    )

    thread.start()

    buffer = ""
    full_response = ""

    for new_text in streamer:

        buffer += new_text
        full_response += new_text

        while True:

            sentence, buffer = extract_complete_sentence(
                buffer
            )

            if sentence is None:
                break

            yield sentence

    # Remaining text
    if buffer.strip():
        yield buffer.strip()

    thread.join()

    conversation_history.append({
        "role": "user",
        "content": user_text
    })

    conversation_history.append({
        "role": "assistant",
        "content": full_response.strip()
    })

In [220]:
test_text = "നമസ്കാരം, ഇന്ന് എങ്ങനെയുണ്ട്?"

In [221]:
print("🤖 Qwen streaming:")
print()

sentences = []

for sentence in stream_qwen_response(test_text):

    print(
        f"\n\n🟢 COMPLETE SENTENCE:\n{sentence}"
    )

    sentences.append(sentence)

print("\n\n✅ Streaming complete")

🤖 Qwen streaming:



🟢 COMPLETE SENTENCE:
നമസ്കാരം!


🟢 COMPLETE SENTENCE:
ഞാൻ അവിടെയുണ്ട്.


🟢 COMPLETE SENTENCE:
നിന്റെ ദിനം എങ്ങനെയുണ്ട്?


✅ Streaming complete


In [222]:
def stream_qwen_to_tts(user_text):

    sentence_count = 0

    for sentence in stream_qwen_response(user_text):

        sentence_count += 1

        print(
            f"\n🔊 TTS sentence {sentence_count}:"
        )

        print(sentence)

        start = time.perf_counter()

        wav = tts(
            sentence,
            speaker=SPEAKER,
            style="NEUTRAL",
            temperature=0.45,
            top_p=0.90,
            top_k=40,
            seed=42,
            max_new_tokens=1000
        )

        output_file = (
            f"/content/stream_sentence_{sentence_count}.wav"
        )

        tts.save(
            output_file,
            wav
        )

        elapsed = time.perf_counter() - start

        print(
            f"⚡ TTS generated in {elapsed:.2f}s"
        )

        display(
            Audio(
                output_file,
                autoplay=True
            )
        )

In [224]:
stream_qwen_to_tts(
    "നമസ്കാരം ബേസിൽ. ഇന്ന് നമുക്ക് AI agents പഠിക്കാം. ആദ്യം voice agent എങ്ങനെ പ്രവർത്തിക്കുന്നു എന്ന് നോക്കാം."
)


🔊 TTS sentence 1:
നമസ്കാരം!
⚡ TTS generated in 3.42s



🔊 TTS sentence 2:
അത് നല്ല തിരിച്ചറിവ്.
⚡ TTS generated in 8.72s



🔊 TTS sentence 3:
വോയ്സ് ആജന്റ് എങ്ങനെ പ്രവർത്തിക്കുന്നു എന്ന് പഠിക്കാൻ ആഗ്രഹിക്ക
⚡ TTS generated in 11.45s


In [225]:
from queue import Queue
import threading
import time
import os

sentence_queue = Queue()
audio_queue = Queue()

In [226]:
def qwen_producer(user_text):

    try:
        for sentence in stream_qwen_response(user_text):

            sentence = sentence.strip()

            if not sentence:
                continue

            print(f"\n📝 Queueing: {sentence}")

            sentence_queue.put(sentence)

    except Exception as e:

        print("❌ Qwen producer error:", e)

    finally:

        # Tell TTS worker that generation is finished
        sentence_queue.put(None)

In [227]:
def tts_worker():

    sentence_number = 0

    while True:

        sentence = sentence_queue.get()

        if sentence is None:

            audio_queue.put(None)

            sentence_queue.task_done()

            break

        try:

            sentence_number += 1

            print(
                f"\n🔊 TTS processing "
                f"sentence {sentence_number}"
            )

            start = time.perf_counter()

            wav = tts(
                sentence,
                speaker=SPEAKER,
                style="NEUTRAL",
                temperature=0.45,
                top_p=0.90,
                top_k=40,
                seed=42,
                max_new_tokens=1000
            )

            output_file = (
                f"/content/stream_audio_{sentence_number}.wav"
            )

            tts.save(
                output_file,
                wav
            )

            elapsed = time.perf_counter() - start

            print(
                f"✅ TTS finished in "
                f"{elapsed:.2f}s"
            )

            audio_queue.put(
                (
                    sentence_number,
                    sentence,
                    output_file
                )
            )

        except Exception as e:

            print(
                f"❌ TTS error: {e}"
            )

        finally:

            sentence_queue.task_done()

In [228]:
def start_pipeline(user_text):

    # Clear old queues
    while not sentence_queue.empty():
        try:
            sentence_queue.get_nowait()
            sentence_queue.task_done()
        except:
            break

    while not audio_queue.empty():
        try:
            audio_queue.get_nowait()
            audio_queue.task_done()
        except:
            break

    qwen_thread = threading.Thread(
        target=qwen_producer,
        args=(user_text,)
    )

    tts_thread = threading.Thread(
        target=tts_worker
    )

    print("🚀 Starting streaming pipeline...")

    qwen_thread.start()
    tts_thread.start()

    return qwen_thread, tts_thread

In [229]:
from IPython.display import Audio, display

def play_pipeline_audio():

    while True:

        item = audio_queue.get()

        if item is None:

            audio_queue.task_done()

            break

        sentence_number, sentence, audio_file = item

        print(
            f"\n▶️ Playing sentence "
            f"{sentence_number}:"
        )

        print(sentence)

        display(
            Audio(
                audio_file,
                autoplay=True
            )
        )

        audio_queue.task_done()

In [231]:
test_text = """
നമസ്കാരം ബേസിൽ. ഇന്ന് നമുക്ക് AI agents പഠിക്കാം.
ആദ്യം voice agent architecture നോക്കാം.
പിന്നീട് memoryയും toolsഉം ചേർക്കാം.
അവസാനം emotion recognition കൂടി ചേർക്കാം.
"""

In [232]:
qwen_thread, tts_thread = start_pipeline(
    test_text
)

play_pipeline_audio()

qwen_thread.join()
tts_thread.join()

print("\n✅ Pipeline complete")

🚀 Starting streaming pipeline...

📝 Queueing: നമസ്കാരം!

🔊 TTS processing sentence 1

📝 Queueing: അത് നല്ല തിരിച്ചറിവ്.
✅ TTS finished in 3.29s

🔊 TTS processing sentence 2

▶️ Playing sentence 1:
നമസ്കാരം!



📝 Queueing: വോയ്സ് ആജന്റിന്റെ ആർക്കിടെക്ചർ എന്താണ് എന്ന് പറയാമോ?

📝 Queueing: എന്താണ് �
✅ TTS finished in 7.78s

🔊 TTS processing sentence 3

▶️ Playing sentence 2:
അത് നല്ല തിരിച്ചറിവ്.


✅ TTS finished in 12.65s

🔊 TTS processing sentence 4

▶️ Playing sentence 3:
വോയ്സ് ആജന്റിന്റെ ആർക്കിടെക്ചർ എന്താണ് എന്ന് പറയാമോ?


✅ TTS finished in 1.69s

▶️ Playing sentence 4:
എന്താണ് �



✅ Pipeline complete


In [238]:
user_text = """
നമസ്കാരം ബേസിൽ. ഇന്ന് നമുക്ക് AI agents പഠിക്കാം.
ആദ്യം voice agent architecture നോക്കാം.
പിന്നീട് memoryയും toolsഉം ചേർക്കാം.
അവസാനം emotion recognition കൂടി ചേർക്കാം.
""".strip()

In [239]:
response = generate_response(user_text)

print("🤖 AI:", response)

output_file = generate_natural_tts(response)

display(
    Audio(
        output_file,
        autoplay=True
    )
)

🤖 AI: നമസ്കാരം! അത് നല്ല തിരിച്ചറിവ്. വോയ്സ് ആജന്റിന്റെ ആർക്കിടെക്ചർ എന്താണ് എന്ന് പറയാമോ? എന്താണ് ആദ്യം പ്രവർത്തിക്കുന്നത്?
🗣️ TTS text:
നമസ്കാരം! അത് നല്ല തിരിച്ചറിവ്. വോയ്സ് ആജന്റിന്റെ ആർക്കിടെക്ചർ എന്താണ് എന്ന് പറയാമോ? എന്താണ് ആദ്യം പ്രവർത്തിക്കുന്നത്?


In [240]:
print("🤖 AI is responding...")

qwen_thread, tts_thread = start_pipeline(
    user_text
)

play_pipeline_audio()

qwen_thread.join()
tts_thread.join()

print("🔄 Ready for next turn")

🤖 AI is responding...
🚀 Starting streaming pipeline...

📝 Queueing: നമസ്കാരം!

🔊 TTS processing sentence 1

📝 Queueing: അത് നല്ല തിരിച്ചറിവ്.
✅ TTS finished in 3.23s

🔊 TTS processing sentence 2

▶️ Playing sentence 1:
നമസ്കാരം!



📝 Queueing: വോയ്സ് ആജന്റിന്റെ ആർക്കിടെക്ചർ എന്താണ് എന്ന് പറയാമോ?

📝 Queueing: എന്താണ് �
✅ TTS finished in 37.24s

🔊 TTS processing sentence 3

▶️ Playing sentence 2:
അത് നല്ല തിരിച്ചറിവ്.


/tmp/ipykernel_2626/496245772.py:28: RuntimeWarning: generation hit max_new_tokens (1000) without emitting <|end_of_speech|> — audio is likely truncated or runaway babble
  wav = tts(


✅ TTS finished in 12.56s

🔊 TTS processing sentence 4

▶️ Playing sentence 3:
വോയ്സ് ആജന്റിന്റെ ആർക്കിടെക്ചർ എന്താണ് എന്ന് പറയാമോ?


✅ TTS finished in 1.70s

▶️ Playing sentence 4:
എന്താണ് �


🔄 Ready for next turn


In [241]:
import time
from IPython.display import Audio, display

def run_streaming_voice_agent():

    global conversation_history

    conversation_history = []

    print("=" * 60)
    print("🎙️ MALAYALAM STREAMING AI VOICE AGENT")
    print("=" * 60)
    print("Speak naturally.")
    print("The system detects when you stop speaking.")
    print("Say 'നിർത്തുക' to stop.")
    print("=" * 60)

    while True:

        try:

            # --------------------------------
            # 1. RECORD
            # --------------------------------

            print("\n🎤 Listening...")

            audio_file = record_until_silence()

            # --------------------------------
            # 2. WHISPER
            # --------------------------------

            print("📝 Transcribing...")

            user_text = transcribe_malayalam(
                audio_file
            ).strip()

            if not user_text:

                print("⚠️ No speech detected.")
                continue

            print(f"\n👤 You: {user_text}")

            # --------------------------------
            # 3. EXIT
            # --------------------------------

            exit_words = [
                "exit",
                "quit",
                "stop",
                "നിർത്തുക",
                "നിർത്തൂ",
                "പോകട്ടെ"
            ]

            if any(
                word in user_text.lower()
                for word in exit_words
            ):

                print("\n👋 Goodbye!")

                break

            # --------------------------------
            # 4. QWEN + TTS PIPELINE
            # --------------------------------

            print("\n🤖 AI responding...")

            start_time = time.perf_counter()

            qwen_thread, tts_thread = start_pipeline(
                user_text
            )

            # --------------------------------
            # 5. PLAY AUDIO
            # --------------------------------

            play_pipeline_audio()

            # --------------------------------
            # 6. WAIT FOR WORKERS
            # --------------------------------

            qwen_thread.join()
            tts_thread.join()

            elapsed = (
                time.perf_counter()
                - start_time
            )

            print(
                f"\n⚡ Response pipeline: "
                f"{elapsed:.2f}s"
            )

            print(
                "\n🔄 Ready for next question..."
            )

        except KeyboardInterrupt:

            print(
                "\n\n👋 Voice agent stopped."
            )

            break

        except Exception as e:

            print(
                f"\n❌ Error: {e}"
            )

            print(
                "🔄 Recovering..."
            )

            continue

In [242]:
run_streaming_voice_agent()

🎙️ MALAYALAM STREAMING AI VOICE AGENT
Speak naturally.
The system detects when you stop speaking.
Say 'നിർത്തുക' to stop.

🎤 Listening...
🎤 Listening...
Speak naturally...


<IPython.core.display.Javascript object>

[transformers] Both `max_new_tokens` (=64) and `max_length`(=448) seem to have been set. `max_new_tokens` will take precedence. Please refer to the documentation for more information. (https://huggingface.co/docs/transformers/main/en/main_classes/text_generation)


📦 Recorded 98.1 KB
✅ Recording complete
📝 Transcribing...

👤 You: എന്റെ തെളിവുകൾ തോമിതാവോ

🤖 AI responding...
🚀 Starting streaming pipeline...

📝 Queueing: നിങ്ങളുടെ തെളിവുകൾ എവിടെ ഉണ്ട്?

🔊 TTS processing sentence 1

📝 Queueing: എനിക്ക് അവ കാണാൻ കഴിയുമോ, അല്ലെങ്കിൽ നിങ്ങൾ എന്തെങ്കിലു�
✅ TTS finished in 10.66s

🔊 TTS processing sentence 2

▶️ Playing sentence 1:
നിങ്ങളുടെ തെളിവുകൾ എവിടെ ഉണ്ട്?


✅ TTS finished in 12.44s

▶️ Playing sentence 2:
എനിക്ക് അവ കാണാൻ കഴിയുമോ, അല്ലെങ്കിൽ നിങ്ങൾ എന്തെങ്കിലു�


...


⚡ Response pipeline: 24.98s

🔄 Ready for next question...

🎤 Listening...
🎤 Listening...
Speak naturally...


<IPython.core.display.Javascript object>

[transformers] Both `max_new_tokens` (=64) and `max_length`(=448) seem to have been set. `max_new_tokens` will take precedence. Please refer to the documentation for more information. (https://huggingface.co/docs/transformers/main/en/main_classes/text_generation)


📦 Recorded 31.7 KB
✅ Recording complete
📝 Transcribing...

👤 You: നിങ്ങോട്ട്

🤖 AI responding...
🚀 Starting streaming pipeline...

📝 Queueing: നിങ്ങോട്ട് എന്താണ് പറയുന്നത്?

🔊 TTS processing sentence 1

📝 Queueing: എന്നോട് വിവരിക്കാമോ?
✅ TTS finished in 8.89s

🔊 TTS processing sentence 2

▶️ Playing sentence 1:
നിങ്ങോട്ട് എന്താണ് പറയുന്നത്?




👋 Voice agent stopped.


In [243]:
from IPython.display import Javascript, display
from google.colab.output import eval_js
import base64
import json
import time

In [244]:
def create_audio_player():

    js = Javascript("""
    window.voiceAgentAudio = new Audio();

    window.playVoiceAudio = function(base64Audio) {

        return new Promise((resolve, reject) => {

            try {

                const binary =
                    atob(base64Audio);

                const bytes =
                    new Uint8Array(
                        binary.length
                    );

                for (
                    let i = 0;
                    i < binary.length;
                    i++
                ) {
                    bytes[i] =
                        binary.charCodeAt(i);
                }

                const blob =
                    new Blob(
                        [bytes],
                        {type: "audio/wav"}
                    );

                const url =
                    URL.createObjectURL(blob);

                window.voiceAgentAudio.src =
                    url;

                window.voiceAgentAudio.onended =
                    () => {

                        URL.revokeObjectURL(url);

                        resolve(true);
                    };

                window.voiceAgentAudio.onerror =
                    (error) => {

                        URL.revokeObjectURL(url);

                        reject(error);
                    };

                window.voiceAgentAudio.play();

            } catch (error) {

                reject(error);
            }
        });
    };

    true;
    """)

    display(js)

    print("🔊 Browser audio player ready.")

In [245]:
create_audio_player()

<IPython.core.display.Javascript object>

🔊 Browser audio player ready.


In [246]:
def play_audio_in_browser(audio_file):

    with open(audio_file, "rb") as f:
        audio_bytes = f.read()

    audio_base64 = base64.b64encode(
        audio_bytes
    ).decode("utf-8")

    js_code = f"""
    playVoiceAudio("{audio_base64}")
    """

    result = eval_js(js_code)

    return result

In [247]:
test_sentence = "നമസ്കാരം ബേസിൽ, ഇന്ന് എങ്ങനെയുണ്ട്?"

In [248]:
wav = tts(
    test_sentence,
    speaker=SPEAKER,
    style="NEUTRAL",
    temperature=0.45,
    top_p=0.90,
    top_k=40,
    seed=42,
    max_new_tokens=1000
)

test_audio_file = "/content/browser_test.wav"

tts.save(
    test_audio_file,
    wav
)

✅ TTS finished in 11.76s


'/content/browser_test.wav'

In [257]:
import base64
from IPython.display import Javascript, display
from google.colab.output import eval_js

def play_audio_in_browser(audio_file):

    with open(audio_file, "rb") as f:
        audio_bytes = f.read()

    audio_base64 = base64.b64encode(
        audio_bytes
    ).decode("utf-8")

    js = f"""
    (async () => {{

        const base64Audio = "{audio_base64}";

        const binary =
            atob(base64Audio);

        const bytes =
            new Uint8Array(
                binary.length
            );

        for (
            let i = 0;
            i < binary.length;
            i++
        ) {{
            bytes[i] =
                binary.charCodeAt(i);
        }}

        const blob =
            new Blob(
                [bytes],
                {{type: "audio/wav"}}
            );

        const url =
            URL.createObjectURL(blob);

        const audio =
            new Audio(url);

        audio.onended = () => {{
            URL.revokeObjectURL(url);
        }};

        await audio.play();

    }})();
    """

    display(
        Javascript(js)
    )

In [258]:
play_audio_in_browser(
    test_audio_file
)

<IPython.core.display.Javascript object>

In [251]:
def play_pipeline_audio_browser():

    while True:

        item = audio_queue.get()

        if item is None:

            audio_queue.task_done()

            break

        sentence_number, sentence, audio_file = item

        print(
            f"\n▶️ Playing sentence "
            f"{sentence_number}:"
        )

        print(sentence)

        start = time.perf_counter()

        try:

            play_audio_in_browser(
                audio_file
            )

        except Exception as e:

            print(
                f"❌ Playback error: {e}"
            )

        elapsed = (
            time.perf_counter()
            - start
        )

        print(
            f"🔊 Playback finished "
            f"in {elapsed:.2f}s"
        )

        audio_queue.task_done()

In [ ]:
create_audio_player()

In [252]:
user_text = """
നമസ്കാരം ബേസിൽ. ഇന്ന് നമുക്ക് AI agents പഠിക്കാം.
ആദ്യം voice agent architecture നോക്കാം.
പിന്നീട് memoryയും toolsഉം ചേർക്കാം.
"""

In [253]:
qwen_thread, tts_thread = start_pipeline(
    user_text
)

🚀 Starting streaming pipeline...


In [259]:
play_pipeline_audio_browser()


▶️ Playing sentence 4:
പിന്നീട് memory എന്താണ് എന്ന് വിവരിക്�


<IPython.core.display.Javascript object>

🔊 Playback finished in 0.01s


In [260]:
qwen_thread.join()
tts_thread.join()

print("✅ Browser streaming test complete")

✅ Browser streaming test complete


In [261]:
run_streaming_voice_agent()

🎙️ MALAYALAM STREAMING AI VOICE AGENT
Speak naturally.
The system detects when you stop speaking.
Say 'നിർത്തുക' to stop.

🎤 Listening...
🎤 Listening...
Speak naturally...


<IPython.core.display.Javascript object>

[transformers] Both `max_new_tokens` (=64) and `max_length`(=448) seem to have been set. `max_new_tokens` will take precedence. Please refer to the documentation for more information. (https://huggingface.co/docs/transformers/main/en/main_classes/text_generation)


📦 Recorded 25.7 KB
✅ Recording complete
📝 Transcribing...

👤 You: Not about this

🤖 AI responding...
🚀 Starting streaming pipeline...

📝 Queueing: ഞാനെന്താ ചെയ്യണം?

🔊 TTS processing sentence 1

📝 Queueing: 😊
✅ TTS finished in 6.20s

🔊 TTS processing sentence 2

▶️ Playing sentence 1:
ഞാനെന്താ ചെയ്യണം?


✅ TTS finished in 2.39s

▶️ Playing sentence 2:
😊


...

✅ TTS finished in 8.70s

▶️ Playing sentence 2:
😊 അല്ലെങ്കിൽ നിന്നെ ബാധിച്ച കാര്യം പറയാമോ?



⚡ Response pipeline: 19.27s

🔄 Ready for next question...

🎤 Listening...
🎤 Listening...
Speak naturally...


<IPython.core.display.Javascript object>

[transformers] Both `max_new_tokens` (=64) and `max_length`(=448) seem to have been set. `max_new_tokens` will take precedence. Please refer to the documentation for more information. (https://huggingface.co/docs/transformers/main/en/main_classes/text_generation)


📦 Recorded 94.5 KB
✅ Recording complete
📝 Transcribing...

👤 You: വായനക്ക് പുറത്തുവിട്ട് പുറത്തുവിട്ട് പുറത്തുവിട്ട് പുറത്തുവിട്ട് പ

🤖 AI responding...
🚀 Starting streaming pipeline...

📝 Queueing: എന്താ വായനക്ക് പുറത്തുവിട്ടത്?

🔊 TTS processing sentence 1

📝 Queueing: 😊 അല്ലെങ്കിൽ നിന്നെ ബാധിച്ച കാര്യം പറയാമോ?


👋 Voice agent stopped.
